# Origini e Adattamenti: Il Peso della Fonte ✍️🎥

**Data Storytelling a cura di Christian Santarelli**

---

### 🎯 L'Obiettivo Narrativo

Siamo abituati a pensare agli anime come semplici "pubblicità in movimento" per manga e light novel. Ma è davvero così? Vogliamo scoprire se l'anime è un semplice veicolo promozionale o se è in grado di trascendere l'opera originale.

In questa analisi esploreremo:
1.  **L'Ecosistema**: Chi comanda davvero il mercato? (Manga, Novel o Originali?)
2.  **Il Bias dell'Originale**: Gli anime nati per lo schermo sono qualitativamente migliori?
3.  **Il Divide Demografico**: Chi guarda cosa? (Un viaggio nei gusti di genere ed età)
4.  **Produzione & Complessità**: Quali fonti richiedono più risorse (cast, studi)?
5.  **Il Decadimento**: Quali adattamenti vengono abbandonati più spesso?

Utilizzeremo un dataset massiccio incrociando dati demografici, recensioni e dettagli di produzione per rispondere alla domanda finale: **L'anime ha bisogno di una fonte per sopravvivere?**

In [30]:
import pandas as pd
import numpy as np
import matplotlib.pyplot as plt
import seaborn as sns
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from pathlib import Path
import sys
import warnings

# Add parent directory to path to import src
sys.path.append('..')
from src.data import load_processed
from src.utils import get_available_memory, print_fancy_progress

# Settings
pd.set_option('display.max_columns', None)
warnings.filterwarnings('ignore')
sns.set_style("whitegrid")
plt.rcParams['figure.figsize'] = (12, 6)

print("Libraries loaded and environment configured. ✅")


Libraries loaded and environment configured. ✅


## 1. Data Preparation 🛠️

Carichiamo una batteria di dataset per avere una visione a 360°:
- **Core**: `details` (metadata), `stats` (numeri)
- **People**: `profiles` (demografica utenti), `reviews` (sentiment)
- **Production**: `person_anime_works` (staff/studi), `character_anime_works` (cast size)

In [31]:
print("Loading datasets... This might take a moment. ⏳")

try:
    # Core Data
    df_details = load_processed("details") # Main metadata
    df_stats = load_processed("stats")     # Scores, members
    
    # Production Data
    # Note: These are large, we might want to aggregate them immediately or load lazily if RAM is tight
    # For now, let's load them and check basic stats.
    # df_person_works = load_processed("person_anime_works")  # For Studios/Staff
    # df_char_works = load_processed("character_anime_works") # For Cast Size
    
    # User Data
    # df_profiles = load_processed("profiles") # For Demographics
    # df_reviews = load_processed("reviews")   # For Variance/Controversy

    print("Core datasets loaded. Loading auxiliary datasets lazily to optimize RAM... ✅")
    
    # Merge Core
    df = df_details.merge(df_stats, on="anime_id", how="inner")
    print(f"Base Dataset merged: {df.shape[0]} anime available.")

except Exception as e:
    print(f"Error loading data: {e}")
    
# Quick peek
df[['title', 'source', 'score', 'members']].head()


Loading datasets... This might take a moment. ⏳
Core datasets loaded. Loading auxiliary datasets lazily to optimize RAM... ✅
Base Dataset merged: 28939 anime available.


,title,source,score,members
0,-Socket-,Original,NaN,195
1,......,Original,6.53,941
2,.hack//G.U. Returner,Game,6.65,22525
3,.hack//G.U. Trilogy,Game,7.06,34264
4,.hack//G.U. Trilogy: Parody Mode,Game,6.35,11135


### Grouping the Source Material

Il campo `source` è molto frammentato. Lo raggruppiamo in 5 Macrocategorie per facilitare l'analisi:

1.  **Manga First**: `Manga`, `4-koma manga`, `Web manga` (Carta/Digitale → Schermo)
2.  **Novel First**: `Light novel`, `Novel`, `Visual novel` (Testo/Gioco Narrativo → Schermo)
3.  **Original**: `Original` (Nato per lo Schermo)
4.  **Game**: `Game`, `Card game` (Gameplay → Schermo)
5.  **Other**: `Music`, `Picture book`, `Radio`, `Other` (Nicchia)

*Nota: `Visual novel` è inserita in Novel First per la natura narrativa, ma analizzeremo anche la sotto-categoria 'Game' separatamente.*

In [32]:
def map_source_group(source):
    if pd.isna(source): return "Unknown"
    source = str(source).strip()
    
    if source in ['Manga', '4-koma manga', 'Web manga', 'Digital manga']:
        return 'Manga First'
    elif source in ['Light novel', 'Novel', 'Visual novel', 'Book']:
        return 'Novel First'
    elif source == 'Original':
        return 'Original'
    elif source in ['Game', 'Card game']:
        return 'Game'
    else:
        return 'Other'

df['source_group'] = df['source'].apply(map_source_group)

# Check distribution
df['source_group'].value_counts()


source_group
Original       12350
Manga First     6499
Other           5138
Novel First     3402
Game            1550
Name: count, dtype: int64

## Capitolo 1: Chi comanda il mercato? (The Ecosystem) 🌍

Prima di parlare di qualità, dobbiamo capire la quantità. Viviamo in un mondo dominato dai Manga o c'è spazio per l'originalità?

Analizzeremo:
1.  **Distribuzione Totale**: Market share delle fonti.
2.  **Evoluzione Temporale**: Come è cambiata l'industria dagli anni '80 a oggi?
3.  **Survival Rate**: Quali fonti generano più sequel?

In [33]:
# 1.1 TreeMap: Distribuzione delle Sources

source_counts = df['source_group'].value_counts().reset_index()
source_counts.columns = ['Source', 'Count']
source_counts['Percent'] = (source_counts['Count'] / source_counts['Count'].sum() * 100).round(1)

fig = px.treemap(source_counts, path=['Source'], values='Count',
                 title='L\'Ecosistema Anime: Distribuzione per Fonte',
                 color='Source',
                 color_discrete_map={'Manga First': '#EF553B', 'Novel First': '#636EFA', 'Original': '#00CC96', 'Game': '#AB63FA', 'Other': '#FFA15A'},
                 hover_data=['Percent'])
fig.update_layout(margin=dict(t=50, l=25, r=25, b=25))
fig.show()

print("Insight: Nota come Original sia una minoranza rispetto a Manga e Novel.")


Insight: Nota come Original sia una minoranza rispetto a Manga e Novel.


In [34]:
# 1.2 Stacked Area Chart: Evoluzione Temporale

# Clean Year
df['start_year'] = df['start_date'].apply(lambda x: int(str(x)[:4]) if pd.notnull(x) and str(x)[:4].isdigit() else np.nan)
df_time = df[(df['start_year'] >= 1980) & (df['start_year'] <= 2024)].copy()

source_trend = df_time.groupby(['start_year', 'source_group']).size().reset_index(name='Count')

fig = px.area(source_trend, x='start_year', y='Count', color='source_group',
              title='L\'Evoluzione delle Fonti (1980-2024)',
              labels={'start_year': 'Anno', 'Count': 'Numero Anime'},
              color_discrete_map={'Manga First': '#EF553B', 'Novel First': '#636EFA', 'Original': '#00CC96', 'Game': '#AB63FA', 'Other': '#FFA15A'})

fig.update_layout(hovermode='x unified')
fig.show()


In [35]:
# 1.3 Bar Chart: "Survival Rate" (Sequels)
# Definiamo sequel se il titolo contiene "Season 2", "2nd Season", "II", ecc, o se è relazionato (semplificazione)
# Un approccio più robusto sarebbe guardare 'related_anime', ma per ora usiamo una proxy sulle entry totali.
# Meglio: guardiamo quante entry ci sono per Source Group in media? 
# No, calcoliamo la % di anime che sono TV (Serie) vs OAV/Movie per vedere la natura dell'investimento.

type_counts = df.groupby(['source_group', 'type']).size().reset_index(name='Count')
total_per_group = df.groupby('source_group').size().reset_index(name='Total')
type_counts = type_counts.merge(total_per_group, on='source_group')
type_counts['Percent'] = (type_counts['Count'] / type_counts['Total'] * 100).round(1)

# Focus su TV Series che sono il formato "principale"
tv_only = type_counts[type_counts['type'] == 'TV'].sort_values('Percent', ascending=False)

fig = px.bar(tv_only, x='source_group', y='Percent',
             title='Percentuale di Serie TV per Fonte (Investimento a Lungo Termine)',
             color='source_group',
             text='Percent',
             labels={'Percent': '% che diventa Serie TV', 'source_group': 'Fonte'},
             color_discrete_map={'Manga First': '#EF553B', 'Novel First': '#636EFA', 'Original': '#00CC96', 'Game': '#AB63FA', 'Other': '#FFA15A'})

fig.update_traces(texttemplate='%{text}%', textposition='outside')
fig.update_layout(uniformtext_minsize=8, uniformtext_mode='hide')
fig.show()


## Capitolo 2: Il "Bias dell'Originale" (Quality vs Quantity) ⭐

Dominare il mercato è facile, ma chi domina la qualità? 

Ipotesi: 
1.  **Original**: Alta variata (rischioso). O Capolavoro o Flop.
2.  **Manga First**: "Usato sicuro". Media più stabile.
3.  **Game**: Difficile da adattare, voti bassi?

In [36]:
# 2.1 Boxplot: Score Distribution per Source Group

df_scored = df[df['score'] > 0]

fig = px.box(df_scored, x='source_group', y='score', color='source_group',
             title='Distribuzione dei Voti per Fonte (Chi ha la media più alta?)',
             points='outliers',
             category_orders={'source_group': ['Novel First', 'Manga First', 'Original', 'Other', 'Game']},
             color_discrete_map={'Manga First': '#EF553B', 'Novel First': '#636EFA', 'Original': '#00CC96', 'Game': '#AB63FA', 'Other': '#FFA15A'})

fig.update_traces(quartilemethod="exclusive") # or "inclusive", or "linear" by default
fig.show()


In [37]:
# 2.2 Ridgeline Plot (Violin): Density of scores for specific Top Sources
# Confrontiamo Manga vs Original vs Light Novel vs Visual Novel vs Game (Specifico)

top_sources = ['Manga', 'Original', 'Light novel', 'Visual novel', 'Game']
df_specific = df[df['source'].isin(top_sources) & (df['score'] > 0)]

# RUOTATO: x='source', y='score', orientation default (v)
fig = px.violin(df_specific, x="source", y="score", color="source", box=True, points=False,
                hover_data=df_specific.columns,
                title='Densita\' dei Voti: Original vs Manga vs Light Novel',
                labels={'source': 'Fonte Specifica', 'score': 'Score'})

fig.show()


In [38]:
# 2.3 Scatterplot Interactive: Episodes vs Score (Zoomable)
# Questo grafico permette di esplorare se le serie lunghe sono prerogativa dei Manga

df_scatter = df[(df['score'] > 0) & (df['episodes'] > 0) & (df['members'] > 1000)].copy()
# Cap episodes a 200 per leggibilità asse X (One Piece e simili saranno outlier visivi)
df_scatter['episodes_capped'] = df_scatter['episodes'].apply(lambda x: 200 if x > 200 else x)

fig = px.scatter(df_scatter, x='episodes', y='score', color='source_group',
                 size='members', hover_name='title',
                 log_x=True, # Log scale per gli episodi è cruciale
                 title='Episodi vs Score: Gli Originali sono più brevi?',
                 labels={'episodes': 'Episodi (Log Scale)', 'score': 'Score', 'members': 'Popolarità'},
                 color_discrete_map={'Manga First': '#EF553B', 'Novel First': '#636EFA', 'Original': '#00CC96', 'Game': '#AB63FA', 'Other': '#FFA15A'})

fig.show()


## Capitolo 3: Il Demographic Divide 👫

Chi è il pubblico di questi adattamenti? 

Per rispondere, carichiamo il dataset `profiles` e aggreghiamo i dati. 
*Nota: Questo passaggio richiede di processare milioni di righe, quindi lavoreremo su un campione aggregato se necessario.*

In [39]:
# 3.1 Grouped Bar Chart: Gender Target by Source
# Analizziamo la colonna 'demographics' (se esiste) che contiene i target espliciti (Shounen, Seinen, ecc.)

demographics_list = ['Shounen', 'Seinen', 'Shoujo', 'Josei', 'Kids']

def extract_demographic(val_str):
    if not isinstance(val_str, str): return 'Unknown'
    # Il valore è una stringa che rappresenta una lista, es: "['Shounen']" o "[]"
    
    for demo in demographics_list:
        if demo in val_str:
            return demo
    return 'General/Unknown'

# Determiniamo quale colonna usare (Preferiamo 'demographics', fallback su 'genres')
target_col = 'demographics' if 'demographics' in df.columns else 'genres'
print(f"Extracting demographics from column: {target_col}")

df['demographic_tag'] = df[target_col].apply(extract_demographic)

# Filtriamo Unknown
df_demo = df[df['demographic_tag'] != 'General/Unknown']

print(f"Found {len(df_demo)} anime with clear demographics.")

demo_source = df_demo.groupby(['source_group', 'demographic_tag']).size().reset_index(name='Count')

fig = px.bar(demo_source, x='source_group', y='Count', color='demographic_tag',
             title='Target Demografico per Fonte (Chi legge cosa?)',
             barmode='group',
             labels={'Count': 'Numero Anime', 'source_group': 'Fonte'})
fig.show()


Extracting demographics from column: demographics
Found 10809 anime with clear demographics.


In [40]:
# 3.2 Heatmap: Age Suitability (Rating) vs Source
# Usiamo la colonna 'rating' (G, PG, R-17, etc)

rating_source = df.groupby(['rating', 'source_group']).size().unstack(fill_value=0)
# Normalize by column (Source) per vedere la % interna
rating_source_norm = rating_source.div(rating_source.sum(axis=0), axis=1)

fig = px.imshow(rating_source_norm, text_auto='.1%', aspect='auto',
                title='Heatmap Rating Età: Quanto sono "maturi" gli Originali?',
                labels=dict(x="Fonte", y="Rating", color="Percentuale"),
                color_continuous_scale='Blues')
fig.show()


In [41]:
# 3.3 Radar Chart: Il Profilo dell'"Otaku Medio" per Fonte
# Confrontiamo alcune metriche medie per fonte: Score, Popularity (Members), Favorites, Episodes

radar_df = df.groupby('source_group')[['score', 'members', 'favorites', 'episodes']].mean().reset_index()

# Normalizziamo (Min-Max scaling) per il Radar Chart altrimenti members schiaccia tutto
from sklearn.preprocessing import MinMaxScaler
scaler = MinMaxScaler()
radar_norm = radar_df.copy()
radar_norm[['score', 'members', 'favorites', 'episodes']] = scaler.fit_transform(radar_norm[['score', 'members', 'favorites', 'episodes']])

fig = go.Figure()

for i, row in radar_norm.iterrows():
    fig.add_trace(go.Scatterpolar(
        r=row[['score', 'members', 'favorites', 'episodes']].values,
        theta=['Score', 'Popolarità', 'Favoriti', 'Lunghezza'],
        fill='toself',
        name=row['source_group']
    ))

fig.update_layout(
  polar=dict(
    radialaxis=dict(
      visible=True,
      range=[0, 1]
    )),
  title='Profilo Caratteristico per Fonte (Valori Normalizzati)'
)

fig.show()
